# SYNCEDSTRUCTURE
### **A Class to handle, crossreference and annotate Structural Proteomics Data**

Credits:
LICENCES:

In [1]:
### <DEPENDENCIES and SyncedStructure Methods display> 
import re, urllib.request, io, copy
import pandas as pd
import seaborn as sns
from synced_structure import SyncedStructure
from viz3d import side_by_side

def get_uniprot(uid):
    u = str(uid).strip().upper()
    if not re.match(r"^([OPQ][0-9][A-Z0-9]{3}[0-9]|[A-NR-Z][0-9]([A-Z][A-Z0-9]{2}[0-9]){1,2})(-\d+)?$", u):
        raise ValueError()
    buf = io.StringIO(urllib.request.urlopen(f"https://rest.uniprot.org/uniprotkb/{u}.fasta").read().decode())
    return u, "".join(buf.read().splitlines()[1:])


pd.set_option("display.width", 1000)
pd.set_option("display.max_columns", None)
pd.set_option("display.max_colwidth", None)
pd.set_option("display.max_rows", 100)

synced_structure_options = dir(SyncedStructure)
d = [x for x in synced_structure_options if x.startswith("__")]
h = [x for x in synced_structure_options
    if x.startswith("_") and not x.startswith("__")]
e = [x for x in synced_structure_options if not x.startswith("_")]
for g in (d, h, e):
  if g:
    [print(g[i : i + 4]) for i in range(0, len(g), 4)]
    print()
### <\DEPENDENCIES and SyncedStructure Methods display>

['__class__', '__contains__', '__delattr__', '__dict__']
['__dir__', '__doc__', '__eq__', '__firstlineno__']
['__format__', '__ge__', '__getattribute__', '__getitem__']
['__getstate__', '__gt__', '__hash__', '__init__']
['__init_subclass__', '__iter__', '__le__', '__len__']
['__lt__', '__module__', '__ne__', '__new__']
['__reduce__', '__reduce_ex__', '__repr__', '__setattr__']
['__sizeof__', '__static_attributes__', '__str__', '__subclasshook__']
['__weakref__']

['_apply_chain_options', '_atom_contacts', '_atom_pair_maps', '_auth_of']
['_block_entries', '_build_chains', '_ca_records', '_chain_colors']
['_chain_description_map', '_chain_entity_map', '_checked_matrix', '_clean_val']
['_compute_interface', '_compute_local_alignment', '_draw_pair', '_entity_sequences']
['_external_refs_for_entity', '_gray_matrix', '_heavy_atoms', '_hydrophobicity']
['_interactive_view', '_keep_mapped', '_label_of', '_local_alignment']
['_make_ca_trajectory', '_make_chain_data', '_make_sidechain_trajectory

## Human Replisome bound to DNA Pol Alpha (8B9D)

Deposited in **RCSB on [October 2022](https://www.rcsb.org/structure/8B9D)**

In this structure, we find a lot of protein chains

In [2]:
### <PDB ID LOADING> 

PDB_ID='8B9D'
sync = SyncedStructure.from_rcsb_id(PDB_ID)
sync_raw = copy.deepcopy(sync)

### <\PDB ID LOADING>

[PYTHON-INFO] 2026-10-16 14:30:31 | Loaded RCSB structure 8B9D | execution time: 8.85s | max memory: 539.9 MB


In [3]:
### <DISPLAY SUMMARY>

print("CHAIN COMPOSITION AND SEQUENCES:\n")
sync_summary = sync.summary()

print(sync_summary) #.drop(columns=['mapped_residues', 'description']))
print()

sync_refseqs , sync_pdbseqs= {}, {}
for chain_id in sync_summary['chain_id']:
    sync_refseqs[chain_id] = sync.get_reference_sequence(chain_id)
    sync_pdbseqs[chain_id] = sync.get_sequence(chain_id)

for chain_id, refseq, pdbseq in zip(sync_summary['chain_id'], sync_refseqs.values(), sync_pdbseqs.values()):
  trunc_ref = refseq[:15] + ("..." if len(refseq) > 15 else "")
  trunc_pdb = pdbseq[:15] + ("..." if len(pdbseq) > 15 else "")
  print(f"Chain {chain_id}: "f"RefSeq ({len(refseq)} aa): {trunc_ref} | "f"PDBSeq ({len(pdbseq)} aa): {trunc_pdb}")


### <\DISPLAY SUMMARY>

CHAIN COMPOSITION AND SEQUENCES:

   chain_id auth_chain_id entity_id                                  description external_ref  sequence_length  reference_length  mapped_residues  mapping_fraction
0         A             2         1        DNA replication licensing factor MCM2       P49736              576               904              576               1.0
1         B             3         2        DNA replication licensing factor MCM3       P25205              569               808              569               1.0
2         C             4         3        DNA replication licensing factor MCM4       P33991              677               863              677               1.0
3         D             5         4        DNA replication licensing factor MCM5       P33992              597               734              597               1.0
4         E             6         5        DNA replication licensing factor MCM6       Q14566              607               821              607 

### Cleaning The Structure

Here we want to 
1. reduce the size of the model
2. remove chains with unclear identity
3. remove any other unwanted chain 

In [4]:
### <DEFINE INTERFACES>
sync_ntd = copy.deepcopy(sync)
keep = ['K', '2', '6','M', 'N']
chains_to_remove = [c for c in sync_ntd.chain_ids if c not in keep]

for chain_id in chains_to_remove:
  sync_ntd.remove_chain(chain_id)

print(sync_ntd.chain_ids)
print(sync_ntd.chain_ids)
### <\DEFINE INTERFACES>

['2', '6', 'K', 'M', 'N']
['2', '6', 'K', 'M', 'N']


In [5]:
### <PALETTE AND PLOTTING>
colors = sns.color_palette("husl", len(sync_raw.chain_ids)).as_hex()
PALETTE = dict(zip(sync_raw.chain_ids, colors))
print(PALETTE)
plot_all_chains = sync_raw.jupy_viz(style='sphere', title="All chains", colors=PALETTE)
plot_clean_chains = sync_ntd.jupy_viz(style='sphere', title="Timeless Interfaces", colors=PALETTE)
side_by_side(plot_all_chains, plot_clean_chains)
### <\PALETTE AND PLOTTING>

{'2': '#f77189', '3': '#f7755a', '4': '#e48432', '5': '#cc9132', '6': '#b89932', '7': '#a69f31', 'A': '#91a531', 'C': '#74ac31', 'D': '#31b338', 'E': '#33b174', 'F': '#34af8d', 'G': '#35ad9d', 'K': '#36acab', 'L': '#37abb9', 'M': '#38a8c9', 'N': '#3aa5e1', 'P': '#689cf4', 'Q': '#9a90f4', 'O': '#be81f4', 'H': '#e16cf4', 'B': '#f560e1', 'J': '#f667c4', 'I': '#f66ca9'}
[PYTHON-INFO] 2026-10-16 14:30:51 | Rendered interactive view of 8B9D at angles (0, 0, 0) | execution time: 8.25s | max memory: 911.5 MB
[PYTHON-INFO] 8B9D: colors ignored for unloaded chains ['3', '4', '5', '7', 'A', 'B', 'C', 'D', 'E', 'F', 'G', 'H', 'I', 'J', 'L', 'O', 'P', 'Q']
[PYTHON-INFO] 2026-10-16 14:30:53 | Rendered interactive view of 8B9D at angles (0, 0, 0) | execution time: 1.61s | max memory: 911.5 MB


### Mapping Timeless Homolog (K) to its UniProtKB reference sequence

Unfortunately out protein of interest, TIM, is not annotated for a valid UniProtKB id in the mmCIF metadata. Thus, we manually retrieve and assign the sequence from `Q9UNS1` accession and we remap positions to match the indexing.

In [6]:
### <DISPLAY CHAIN MAP>
print(sync_ntd.summary())
print()
### <\DISPLAY CHAIN MAP>

  chain_id auth_chain_id entity_id                            description external_ref  sequence_length  reference_length  mapped_residues  mapping_fraction
0        A             2         1  DNA replication licensing factor MCM2       P49736              576               904              576               1.0
1        E             6         5  DNA replication licensing factor MCM6       Q14566              607               821              607               1.0
2        M             K        13               Protein timeless homolog       Q9UNS1              638              1209              638               1.0
3        O             M        15                     Leading strand DNA         None                0                84                0               0.0
4        P             N        16                           DNA Molecule         8B9D                0                86                0               0.0



In [7]:
### <INTERFACE REMAP AND EXPORT>
import re, pickle
uniprot_pattern = re.compile(r"^([OPQ][0-9][A-Z0-9]{3}[0-9]|[A-NR-Z][0-9]([A-Z][A-Z0-9]{2}[0-9]){1,2})(-\d+)?$")
UPIDS = list(set([u for u in sync_ntd.summary()["external_ref"] if isinstance(u, str) and uniprot_pattern.match(u)]))
for _, r in sync_ntd.summary()[sync_ntd.summary()["external_ref"].isin(UPIDS)].iterrows():
    sync_ntd.set_reference_sequence(chain_id=r["auth_chain_id"], sequence=get_uniprot(r["external_ref"])[1])
    sync_ntd.remap_chain(r["auth_chain_id"])
sync_ntd.save_pdb(output_path="tutorial-data/TIM-interface.pdb", numbering="reference")
with open("tutorial-data/TIM-interface.pkl", "wb") as f:
    pickle.dump(sync_ntd, f)
### <\INTERFACE REMAP AND EXPORT>

remapped 2
    chain_id auth_chain_id  pdb_resnum  sequence_index  reference_index
573        A             2         818             574              818
574        A             2         819             575              819
575        A             2         820             576              820
remapped 6
    chain_id auth_chain_id  pdb_resnum  sequence_index  reference_index
604        E             6         659             605              659
605        E             6         660             606              660
606        E             6         661             607              661
remapped K
    chain_id auth_chain_id  pdb_resnum  sequence_index  reference_index
635        M             K         804             636              804
636        M             K         805             637              805
637        M             K         806             638              806


PosixPath('tutorial-data/TIM-interface.pdb')

In [8]:
### <CHAIN DETAIL VISUALIZATION>
left = sync.jupy_viz(chain_id="K", style="sphere", title="Protein Timeless Homolog (Q9UNS1)", colors=PALETTE)
right = sync.jupy_viz(chain_id="K", style="cartoon", title="Protein Timeless Homolog (Q9UNS1)", colors=PALETTE)
side_by_side(left, right)
### <\CHAIN DETAIL VISUALIZATION>

[PYTHON-INFO] 2026-10-16 14:31:01 | Rendered interactive view of 8B9D at angles (0, 0, 0) | execution time: 4.79s | max memory: 965.5 MB
[PYTHON-INFO] 2026-10-16 14:31:05 | Rendered interactive view of 8B9D at angles (0, 0, 0) | execution time: 4.73s | max memory: 968.4 MB
